---
title: "Análisis Exploratorio de Datos: Ruta El Silencio"
---

In [30]:
import pandas as pd
import numpy as np
from pathlib import Path
import sys

PROJECT_ROOT = Path.cwd().parent

SRC_PATH = PROJECT_ROOT / "src"
DATA_RAW = PROJECT_ROOT /"data"  /"raw"
DATA_PROCESSED = PROJECT_ROOT / "data" /"processed"

if str(SRC_PATH) not in sys.path:
    sys.path.append(str(SRC_PATH))

from utils import eda_toolkit as toolkit

df = pd.read_parquet(DATA_RAW / "timbradas_anio_silencio.parquet")
df = df.drop(columns=["id_ruta", "nombre_ruta"])

df_prog = pd.read_parquet(DATA_RAW / "progvehiculos_silencio.parquet")

df = df[df["ano"].isin([2023, 2024, 2025])].copy()

df["fecha_inicio"] = pd.to_datetime(df["fecha_inicio"]).dt.date
df["fecha_fin"] = pd.to_datetime(df["fecha_fin"]).dt.date

df["id_estacionalidad_anio"] = df["id_estacionalidad_anio"].astype("int16")
df["promedio_subidas"]       = df["promedio_subidas"].astype("float32")
df["promedio_bajadas"]       = df["promedio_bajadas"].astype("float32")

:::{admonition} Resumen del análisis exploratorio
:class: info
- Estructura temporal idéntica a K54: ciclos semi-diurno (32-33), diario (65) y semanal (455), independientes entre sí.
- Perfil intradía bimodal con una diferencia: SILENCIO tiene pico matutino único a las 05:30, K54 dos crestas similares. Ratio AM/PM ~1,7 en SILENCIO vs. ~1,4 en K54.
- Demanda absoluta ~mitad de K54 (~12.000 vs. ~22.400 pax/día), con ~146 despachos/día vs. ~269. Ocupación por viaje similar.
- Caída interanual sostenida (2023 → 2025) en casi todos los meses y días, con reversión parcial en 2025.
- Estacionalidad con misma jerarquía que K54 (corrientes > Fiesta Atlántico > Temporada > Festivo Nacional).
- Demanda registrada ≠ demanda potencial: un cero puede reflejar ausencia de despacho, no de demanda.
:::

## Introducción

La demanda de pasajeros en sistemas de transporte masivo urbano es una variable operativa crítica, sensible a patrones horarios, calendarios laborales, eventos estacionales y shocks exógenos. El modelado de la demanda en sistemas tipo BRT evoluciona hacia arquitecturas híbridas que integran series temporales agregadas con información contextual, y que se traducen operativamente en decisiones de frecuencia de despacho, dimensionamiento de flota y asignación de capacidad por ruta.

La serie analizada proviene de los registros de demanda y de flota asociados a la ruta EL SILENCIO operada por SOBUSA en el Sistema de Transporte Masivo de Barranquilla. Los registros consolidados (`timbradas_anio_silencio`) contienen las dimensiones temporales y estacionales, junto con las métricas operativas agregadas. Los registros de flota (`progvehiculos`) contienen la información individual de cada despacho.

:::{admonition} Información: Dataset de Demanda y Flota — Ruta EL SILENCIO
:class: info

Los registros consolidados (`timbradas_anio_silencio`) comprenden 7,685 observaciones para la ruta EL SILENCIO, con estructura de franjas horarias de 15 minutos entre 00:00 y 23:45. Contienen las dimensiones temporales (año, día de la semana, franja horaria) y estacionales (tipo de estacionalidad, nombre de evento), junto con las métricas operativas agregadas (`subidas`, `bajadas`, `nro_viajes`, `promedio_subidas`, `promedio_bajadas`).

Los registros de flota (`progvehiculos`) contienen la información individual de cada despacho: fecha-hora de inicio y fin, vehículo, conductor, pasajeros transportados, cancelaciones y estado operativo.

El período analizado (2023–2025) abarca múltiples regímenes operativos. Estos incluyen la operación regular de días corrientes, los festivos nacionales, las temporadas estacionales y las fiestas patronales, además de los ciclos anuales diferenciados.
:::

La ruta EL SILENCIO tiene una longitud total de 62.9 km y recorre el área metropolitana de Barranquilla de sur a norte, con inicio en la zona sur y punto de retorno al noroccidente. Ida y vuelta comparten parcialmente el corredor en el tramo central. El sentido de operación y el punto de retorno se ilustran en el mapa presentado a continuación.

In [3]:
_, _ = toolkit.generate_map("silencio")

Esta libreta documenta el Análisis Exploratorio de Datos (EDA) de esta ruta: evaluación de la integridad de la base de datos, detección de registros faltantes, discontinuidades en el calendario operativo, análisis de consistencia entre los registros consolidados y los registros de flota, y tratamiento de anomalías. También documenta el análisis de estacionalidad horaria, semanal y anual.

## Análisis preliminar

### Registros consolidados

El conjunto de datos crudo estuvo compuesto por 10,374 registros consolidados (`timbradas_anio_silencio`) correspondientes a la operación de la ruta EL SILENCIO, abarcando un rango temporal de 2023 a 2026. El dataset original cuenta con 19 variables que combinan dimensiones temporales, dimensiones estacionales y métricas operativas agregadas.

Por instrucción de la empresa, el análisis se limitó al cierre de 2025, quedando excluido el año 2026. Tras este filtro, el conjunto de datos quedó compuesto por 7,685 registros consolidados, abarcando de 2023 a 2025. Las columnas constantes (`id_ruta`, `nombre_ruta`) se eliminaron por no aportar variabilidad al análisis, quedando 17 variables efectivas. Éstas se almacenaron en tipos enteros de distinta precisión (`int8`, `int16`, `int32`), tipos temporales (`time`, `date`), cadenas de texto y valores de precisión simple (`float32`). Las métricas operativas (`subidas`, `bajadas`, `nro_viajes`) se almacenaron en formato entero, mientras que los promedios por viaje se almacenaron en precisión simple. No se observaron datos faltantes en ninguna de las variables analizadas.

In [2]:
_ = toolkit.dataframe_integrity_blocks(df, n_blocks=3)

Variable,Data type,Variable,Data type,Variable,Data type
ano,int16,minuto_num,int8,subidas,int32
id_dia_semana,int8,tipo_estacionalidad,str,bajadas,int32
id_estacionalidad_anio,int16,nombre_evento,str,nro_viajes,int32
hora_inicio,time,fecha_inicio,date,promedio_subidas,float32
hora_fin,time,fecha_fin,date,promedio_bajadas,float32
hora_num,int8,duracion_evento_dias,int16,,


El análisis de la tabla consolidada reveló que sus registros no representan días particulares sino patrones operativos: cada fila combina un año, un día de la semana, una estacionalidad y una franja horaria, y acumula las métricas sobre todos los días del período que comparten esa combinación. Un registro de "lunes en días corrientes de 2023", por ejemplo, no corresponde a un lunes específico sino al agregado de los ~50 lunes del año. Esta estructura impide reconstruir series temporales diarias confiables, situación ya documentada en detalle en el análisis exploratorio de la ruta Cra 54 (K54). Siguiendo el método descrito allí, se usa `progvehiculos` para reconstruir la demanda por franjas de forma fiable

In [3]:
_ = toolkit.dataframe_head_table(df, n=5)

ano,id_dia_semana,id_estacionalidad_anio,hora_inicio,hora_fin,hora_num,minuto_num,tipo_estacionalidad,nombre_evento,fecha_inicio,fecha_fin,duracion_evento_dias,subidas,bajadas,nro_viajes,promedio_subidas,promedio_bajadas
2023,1,121,07:45:00,08:00:00,7,45,FESTIVO_NACIONAL,Día de los Reyes Magos,2023-01-09,2023-01-09,1,53,44,1,53.000000,44.000000
2023,1,121,08:00:00,08:15:00,8,0,FESTIVO_NACIONAL,Día de los Reyes Magos,2023-01-09,2023-01-09,1,31,31,1,31.000000,31.000000
2023,1,121,08:15:00,08:30:00,8,15,FESTIVO_NACIONAL,Día de los Reyes Magos,2023-01-09,2023-01-09,1,101,108,3,33.669998,36.000000
2023,1,121,08:30:00,08:45:00,8,30,FESTIVO_NACIONAL,Día de los Reyes Magos,2023-01-09,2023-01-09,1,43,45,1,43.000000,45.000000
2023,1,121,08:45:00,09:00:00,8,45,FESTIVO_NACIONAL,Día de los Reyes Magos,2023-01-09,2023-01-09,1,91,93,2,45.500000,46.500000


### Registros de flota

El conjunto de datos de flota (`progvehiculos`) estuvo compuesto por 161,595 registros individuales de despacho correspondientes a la operación de la ruta EL SILENCIO, abarcando un rango temporal de 2023 a 2026. Se cuenta con 74 variables que describen cada viaje en detalle, almacenadas en tipos enteros, flotantes, temporales, booleanos, categóricos y de texto. La clasificación operativa de los registros según su estado de finalización revela que el 90.6% de los viajes fueron completados, el 9.4% cancelados y una fracción marginal (3 casos) quedó en estado incompleto.

Los viajes cancelados, aunque interrumpidos, registraron un promedio de aproximadamente 73 pasajeros por viaje, lo que indica que la operación se ejecutó parcialmente antes de la cancelación. Esta evidencia sugiere que la cancelación no implica ausencia de demanda, sino una interrupción del servicio durante el recorrido, y por lo tanto estos registros se conservan en el análisis por representar abordajes efectivos.

In [4]:
_, _, _ = toolkit.plot_trip_status(
    df_prog, title="Estado de los viajes — El Silencio (2023–2025)", y_label_pad=10,
    status_labels=("Completado", "Incompleto", "Cancelado")
)

La mayoría de las 74 variables describen eventos que ocurren durante o después del viaje, por lo que no pueden emplearse como predictores sin incurrir en fuga de información. Las métricas operativas, los atributos de resultado, las variables de recaudo y los campos de auditoría reflejan el resultado de la operación, no las condiciones previas al despacho. Por este motivo, el conjunto se redujo a seis variables conocidas antes de que el viaje arranque. Las dos columnas de estado (`finalizado` y `cancelada`) se consolidaron en un único indicador binario, `es_cancelado`, que preserva la información operativa sin redundancia y permite distinguir directamente los viajes completados de los cancelados.

In [31]:
cols_finales = [
    "numeropasajeros",
    "fechainicio",
    "fechasalida",
    "fechafin",
    "finalizado",
    "cancelada",
    "idprogramacion",
    "idvehiculo",
]

df_prog = df_prog[[c for c in cols_finales if c in df_prog.columns]].copy()

df_prog["fechainicio"] = pd.to_datetime(df_prog["fechainicio"])
df_prog["fechasalida"] = pd.to_datetime(df_prog["fechasalida"])
df_prog["fechafin"]    = pd.to_datetime(df_prog["fechafin"])

df_prog = df_prog[
    (df_prog["fechainicio"].dt.year.isin([2023, 2024, 2025])) &
    ~((df_prog["finalizado"] != "S") & (df_prog["cancelada"] != "S"))
].copy()

df_prog["es_cancelado"] = (df_prog["cancelada"] == "S").astype("int8")
df_prog = df_prog.drop(columns=["finalizado", "cancelada"])

_ = toolkit.dataframe_integrity_blocks(df_prog, n_blocks=2)

Variable,Data type,Variable,Data type
numeropasajeros,int32,idprogramacion,int64
fechainicio,Timestamp,idvehiculo,str
fechasalida,Timestamp,es_cancelado,int8
fechafin,Timestamp,,


Cada fila de la tabla resultante representa un viaje individual. Las columnas describen ese viaje desde tres dimensiones: sus marcas temporales (`fechainicio`, `fechasalida`, `fechafin`), sus identificadores operativos (`idprogramacion`, `idvehiculo`) y su estado (`es_cancelado`). La variable objetivo, numeropasajeros, es un conteo agregado por viaje, sin resolución intra-viaje: no se registra cuándo ni dónde abordó cada pasajero, solo el total acumulado al cierre. La inspección de las primeras filas revela valores faltantes.

In [6]:
_ = toolkit.dataframe_head_table(df_prog, n=5)

numeropasajeros,fechainicio,fechasalida,fechafin,idprogramacion,idvehiculo,es_cancelado
70,2023-01-01 05:11:05,2023-01-01 05:20:00,2023-01-01 08:11:08,5061795,SOBUSA441,0
0,2023-01-01 05:14:16,2023-01-01 05:10:00,2023-01-01 08:16:52,5061794,SOBUSA25,0
,2023-01-01 05:20:44,2023-01-01 05:00:00,NaT,5061793,SOBUSA112,1
40,2023-01-01 05:29:54,2023-01-01 05:44:00,NaT,5061804,SOBUSA244,1
,2023-01-01 05:31:28,2023-01-01 05:28:00,NaT,5061796,SOBUSA319,1


El perfil de faltantes replica el patrón documentado en el análisis de la Ruta K54: las ausencias se concentran en `fechafin` y `numeropasajeros`, mientras que las marcas de inicio y los identificadores operativos están completos en la totalidad de los registros. En cifras absolutas, SILENCIO presenta menos casos faltantes que K54 en ambas columnas (15,176 frente a 16,089 en `fechafin`, y 1,497 frente a 2,772 en `numeropasajeros`), aunque en proporción la ausencia de fechafin es mayor (9.4% frente a 5.4%) debido al menor tamaño del dataset. La proporción de faltantes en `numeropasajeros` es idéntica en ambas rutas (0.93%).

In [32]:
nulos = (
    df_prog
    .isna()
    .sum()
    .to_frame(name="n_nulos")
)

nulos["pct_nulos"] = (nulos["n_nulos"] / len(df_prog) * 100).round(2)
nulos["n_validos"] = len(df_prog) - nulos["n_nulos"]
nulos = nulos.sort_values("pct_nulos", ascending=False)

_ = toolkit.dataframe_head_table(nulos.reset_index().rename(columns={"index": "variable"}),
                         n=len(nulos))

variable,n_nulos,pct_nulos,n_validos
fechafin,15176,9.390000,146413
numeropasajeros,1497,0.930000,160092
fechainicio,0,0.000000,161589
fechasalida,0,0.000000,161589
idprogramacion,0,0.000000,161589
idvehiculo,0,0.000000,161589
es_cancelado,0,0.000000,161589


Tras excluir los registros sin conteo de pasajeros, que no aportan demanda a ninguna franja y carecen de variable objetivo para el modelado, el dataset conserva 14,894 viajes con `fechafin` nulo, todos correspondientes a viajes cancelados. Estos registros mantienen su conteo de demanda y se preservan para el análisis, ya que la duración del recorrido no resulta indispensable para el modelado por franja.

El chequeo de consistencia temporal identificó 372 viajes con `fechafin` anterior a `fechasalida`. El análisis de la demanda asociada a estos registros confirma que no representan operación comercial: concentran 235 pasajeros en total (0.002% de la demanda del período), con una mediana de cero pasajeros por viaje frente a 74 en el resto del dataset. Desagregando por magnitud del desfase, 361 de los 372 viajes (97%) corresponden a diferencias menores a 15 minutos y aportan apenas 0.19 pasajeros por viaje en promedio, un perfil compatible con salidas vacías cuya marca de cierre quedó desfasada.

In [33]:
df_prog_check = df_prog.loc[
    df_prog["numeropasajeros"].notna() & (df_prog["es_cancelado"] == 0)
].copy()

df_prog_check["duracion_min"] = (
    (df_prog_check["fechafin"] - df_prog_check["fechasalida"])
    .dt.total_seconds() / 60
).round(1)

df_incons = df_prog_check[df_prog_check["duracion_min"] <= 0].copy()

cols = ["numeropasajeros", "fechainicio", "fechafin", "duracion_min",
        "idprogramacion", "idvehiculo"]

top_incons = (
    df_incons[cols]
    .sort_values("duracion_min")
    .head(10)
    .reset_index(drop=True)
)

styled = (
    top_incons.style
    .hide(axis="index")
    .set_table_styles(toolkit._table_style_rules())
    .format({"duracion_min": "{:.1f}"})
)

toolkit._render_styled(styled)

numeropasajeros,fechainicio,fechafin,duracion_min,idprogramacion,idvehiculo
36,2023-12-15 10:14:55,2023-12-06 11:51:59,-12862.0,5856638,SOBUSA112
20,2025-02-26 13:28:31,2025-02-25 12:37:29,-1502.5,6852798,SOBUSA538
1,2024-11-27 05:08:18,2024-11-27 04:01:05,-78.9,6645379,SOBUSA05
5,2024-12-02 05:33:45,2024-12-02 04:53:17,-54.7,6656948,SOBUSA85
0,2024-11-30 16:53:59,2024-11-30 16:02:53,-51.1,6654806,SOBUSA112
94,2024-11-13 05:04:08,2024-11-13 04:18:00,-42.0,6613126,SOBUSA340
0,2024-11-30 17:15:38,2024-11-30 16:34:42,-31.3,6654843,SOBUSA467
0,2024-11-30 16:36:22,2024-11-30 15:58:59,-31.0,6654777,SOBUSA27
8,2024-11-30 16:42:08,2024-11-30 16:08:21,-27.6,6654791,SOBUSA485
0,2024-11-30 16:23:28,2024-11-30 15:56:10,-21.8,6654714,SOBUSA181


Los 11 viajes restantes, con diferencias mayores, concentran 166 pasajeros pero siguen siendo marginales en términos absolutos: su exclusión no altera ninguna franja horaria en más de 94 pasajeros ni ningún día en más del 0.8% de su demanda. Por consistencia con el criterio aplicado en la Ruta K54, se excluyeron del análisis.

Una vez depurados los registros faltantes y las inconsistencias temporales, se incorporó la variable `duracion_min` al dataset, calculada como la diferencia en minutos entre `fechasalida` y `fechafin`. Esta variable se conserva en `df_prog` porque permite verificar la consistencia operativa de los viajes y servirá como referencia para los análisis posteriores de calidad y de modelado.

In [34]:
df_prog["duracion_min"] = (
    (df_prog["fechafin"] - df_prog["fechasalida"])
    .dt.total_seconds() / 60
)

df_prog = df_prog[df_prog["numeropasajeros"].notna()].copy()

mask_cancelado = df_prog["es_cancelado"] == 1
mask_inconsistente = (df_prog["duracion_min"] <= 0) & (~mask_cancelado)

df_prog = df_prog[~mask_inconsistente].copy()

## Análisis de valores atípicos

Antes de agregar los viajes por franja horaria es indispensable determinar qué registros son válidos. La tabla de flota contiene 159,720 viajes, y no todos corresponden a operaciones reales: algunos tienen valores incompatibles con la capacidad de un bus, otros presentan duraciones que exceden el ciclo normal de la ruta, y otros muestran tasas de recogida atípicas. Incluirlos distorsionaría las estimaciones de demanda y las recomendaciones de frecuencia.

El análisis de calidad usa dos criterios operativos: el número de pasajeros por viaje, acotado por la capacidad máxima de un bus articulado, y la duración del recorrido, acotada por el ciclo completo de la ruta. Ambos permiten descartar valores imposibles sin depender de supuestos distribucionales.

:::{admonition} Información: Filtro Hampel
:class: info

El filtro Hampel detecta valores atípicos usando estadística robusta. Para cada observación $x_i$ se considera una ventana centrada de $2k + 1$ vecinos y se calculan dos estadísticos locales:

$$
m_i = \text{mediana}\left( x_j \right), \quad \text{y} \quad \text{MAD}_i = \text{mediana}\left(\left| x_j - m_i \right| \right), \quad j \in [i-k, i+k]
$$

donde $m_i$ es la mediana local y $\text{MAD}_i$ la desviación absoluta mediana respecto a ella. Una observación se marca como atípica cuando su desviación excede un múltiplo del MAD:

$$
\frac{|x_i - m_i|}{1.4826 \cdot \text{MAD}_i} > t
$$

El factor $1.4826$ escala la MAD para que sea consistente con la desviación estándar bajo normalidad, y $t$ es el umbral en unidades de desviaciones estándar equivalentes (típicamente entre 3 y 5). La elección de mediana y MAD en lugar de media y desviación estándar es lo que da robustez al método: ambas son resistentes a outliers, mientras que los momentos clásicos se ven distorsionados por ellos.
:::

El análisis de calibración mostró que la curva de observaciones retenidas se aplana a partir de 4.5 MADs: por encima de ese punto cada incremento del umbral recupera menos de 350 casos. Se adoptó un umbral de 5.0 MADs por ser un estándar consolidado en detección de outliers y marcar únicamente el 0.36% de los viajes con conteo válido (567 observaciones). Este valor se sitúa en la zona de rendimientos decrecientes de la curva, lo que indica que umbrales más altos no aportan ganancias significativas de cobertura en este caso.

In [9]:
_, _, resumen = toolkit.calibrate_hampel_threshold(
    df_prog, col="numeropasajeros",
    col_order="fechasalida",
    t_values=(3.0, 3.5, 4.0, 4.5, 5.0, 5.5, 6.0, 6.5, 7.0),
    k=7, title="Calibración Hampel sobre número de pasajeros", x_label_pad=12, y_label_pad=18,
    xlab="Umbral $t$ (MADs)"
)

El filtro Hampel aplicado únicamente sobre el conteo de pasajeros no permite confirmar por sí solo la existencia de un error: un valor alto puede corresponder a un bus lleno en hora pico y uno bajo a un viaje legítimo en hora valle. Para robustecer la detección se derivó la duración del viaje a partir de las marcas temporales de inicio y fin de cada despacho, y se aplicó el mismo filtro sobre esa nueva variable. Los viajes cancelados, que no registran hora de finalización, se excluyeron de esta calibración por carecer de la información necesaria.

In [10]:
resumen_mostrar = resumen[["t", "n_retained", "n_flagged"]].copy()
resumen_mostrar = resumen_mostrar.rename(columns={
    "t": "umbral t",
    "n_retained": "n_retenidos",
    "n_flagged": "n_marcados",
})
resumen_mostrar["umbral t"] = resumen_mostrar["umbral t"].map(lambda x: f"{x:.1f}")
resumen_mostrar["delta_retenidos"] = resumen_mostrar["n_retenidos"].diff()
resumen_mostrar["delta_retenidos"] = resumen_mostrar["delta_retenidos"].fillna(0).astype(int)

_ = toolkit.dataframe_head_table(resumen_mostrar, n=len(resumen_mostrar))

umbral t,n_retenidos,n_marcados,delta_retenidos
3.0,155703,4017,0
3.5,157379,2341,1676
4.0,158308,1412,929
4.5,158828,892,520
5.0,159153,567,325
5.5,159344,376,191
6.0,159464,256,120
6.5,159520,200,56
7.0,159580,140,60


A diferencia del conteo de pasajeros, la duración del viaje no presenta un codo claro en la curva de calibración: los incrementos por encima de cada umbral decrecen de forma progresiva (de 1,354 casos en 3.5 MADs a 358 en 7.0) sin un punto donde los valores legítimos terminen abruptamente. Se adoptó el mismo umbral de 5.0 MADs utilizado para el filtro de pasajeros, priorizando la consistencia metodológica entre variables sobre la optimización individual del umbral. BBajo este criterio se marcan 8,886 observaciones (6.1% de los viajes no cancelados), una proporción considerablemente mayor que la del filtro de pasajeros (0.36%), consistente con la mayor variabilidad natural de la duración.

In [11]:
df_prog_dur = df_prog.copy()
df_prog_dur["duracion_min"] = (
    (df_prog_dur["fechafin"] - df_prog_dur["fechasalida"])
    .dt.total_seconds() / 60
)

df_prog_dur = df_prog_dur[df_prog_dur["duracion_min"].notna()].copy()

_, _, resumen_dur = toolkit.calibrate_hampel_threshold(
    df_prog_dur, col="duracion_min", col_order="fechasalida",
    t_values=(3.0, 3.5, 4.0, 4.5, 5.0, 5.5, 6.0, 6.5, 7.0),
    k=7, title="Calibración Hampel sobre duración del viaje",
    ylab="Observaciones retenidas", x_label_pad=12, y_label_pad=18,
    xlab="Umbral $t$ (MADs)"
)


La asociación entre ambos criterios fue estadísticamente significativa ($\chi^2$ = 421.03, $p$ < 0.001), aunque el tamaño del efecto medido por V de Cramér fue pequeño ($V$ = 0.051). El odds ratio de 5.85 indica que, entre los viajes marcados por duración anómala, el odds de estar marcado también por conteo anómalo es 5.85 veces el de los viajes no marcados por duración. Sin embargo, la magnitud global de la asociación es modesta: solo el 1.6% de los viajes marcados por duración presentan también conteo anómalo, lo que confirma que los filtros capturan fenómenos parcialmente superpuestos más no redundantes. La aplicación conjunta de ambos criterios se justifica tanto por su significancia estadística como por su capacidad de detectar casos que cada uno individualmente no capturaría.

In [12]:
resumen_dur_mostrar = resumen_dur[["t", "n_retained", "n_flagged"]].copy()
resumen_dur_mostrar = resumen_dur_mostrar.rename(columns={
    "t": "umbral t",
    "n_retained": "n_retenidos",
    "n_flagged": "n_marcados",
})
resumen_dur_mostrar["umbral t"] = resumen_dur_mostrar["umbral t"].map(lambda x: f"{x:.1f}")
resumen_dur_mostrar["delta_retenidos"] = (
    resumen_dur_mostrar["n_retenidos"].diff().fillna(0).astype(int)
)

_ = toolkit.dataframe_head_table(resumen_dur_mostrar, n=len(resumen_dur_mostrar))

umbral t,n_retenidos,n_marcados,delta_retenidos
3.0,132108,12718,0
3.5,133462,11364,1354
4.0,134466,10360,1004
4.5,135287,9539,821
5.0,135940,8886,653
5.5,136491,8335,551
6.0,136981,7845,490
6.5,137392,7434,411
7.0,137750,7076,358


La inspección de los diagramas de cajas para la ruta El Silencio muestra que el número de pasajeros se concentra principalmente entre 48 y 104 pasajeros por viaje, con una mediana de 74. Los umbrales Hampel calculados sobre esta variable (t = 5.0) sitúan el límite inferior en -133.6 y el superior en 281.6, lo que confirma que el conteo no presenta valores atípicos bajos y que solo unas pocas observaciones superan el límite superior, incluyendo algunos registros por encima de 300 pasajeros. En cuanto a la duración, la mayoría de los viajes se concentra aproximadamente entre 202 y 261 minutos, con una mediana de 237.4. Los umbrales Hampel (24.6 y 450.1) separan el rango de duraciones plausibles de los casos extremos: duraciones cercanas o inferiores a cero y otras que superan los 450 minutos hasta valores por encima de 500.

In [13]:
_, _, tabla = toolkit.plot_hampel_boxplots(
    df_prog,
    t=(5.0, 5.0),
    titles=("Número de pasajeros", "Duración (min)"),
    ylim_passengers=(-49, 400),
    ylim_duration=(-49, 600),
)

### Duración de los viajes

El análisis por umbrales de duración revela una discontinuidad pronunciada entre 90 y 120 minutos. Bajo el corte heredado de K54 (90 min) se identificaban 1,514 viajes (0.95%) sin patrón horario claro. Con un corte de 120 minutos, duración mínima físicamente compatible con recorrer los 62.9 km a velocidad operativa realista (31.5 km/h), el conteo asciende a 5,427 viajes (3.40%) y aparece una concentración en la hora 5: 17.6% de esa franja frente a 1.1% en el resto del día.

El fenómeno se localiza con precisión en el rango 90–108 minutos: de los 2,454 viajes en ese intervalo, 2,312 (94.2%) ocurren en la hora 5 y todos cierran entre las 6:00 y las 7:59, configurando una ventana operativa consistente de aproximadamente dos horas. No son registros vacíos ni primeras salidas del vehículo: el 97.5% tiene pasajeros (mediana 37) y solo el 0.3% corresponde al primer viaje del día. Los 2,315 casos se distribuyen sobre 104 vehículos distintos, con una media de 22 viajes por vehículo a lo largo del período, lo que confirma un patrón estable de la flota y no un evento puntual. Se adopta el corte de 120 minutos por su justificación física y porque la tasa interna de la hora 5 se estabiliza a partir de ese punto.

In [35]:
df_temp = df_prog.copy()
df_temp["hora"] = df_temp["fechasalida"].dt.hour

fig, ax, tabla = toolkit.plot_short_trips_by_hour(
    df_temp, threshold_min=120,
    title="Viajes con duración inferior a 120 min por hora",
    ylab="Tasa dentro de la hora (%)", xlab = "Hora del día"
)

El sistema conserva 138 registros con `fechainicio` entre las 21:00 y las 23:00, pero ninguno corresponde a una salida física en esa franja: sus `fechasalida` se ubican entre las 5:00 y las 20:59, con la gran mayoría concentrada entre las 17:00 y las 20:00, dentro de la ventana operativa de la ruta (04:30–20:30). Son producto de sincronización diferida del dispositivo a bordo, con un desfase mediano de 206.7 minutos (3.4 horas) entre la salida real y el sello del sistema, consistente con la acumulación de registros sin conexión durante el turno y su descarga al regresar al patio.

Bajo la convención de hora de salida física, la ruta no registra operación comercial después de las 20:59. El conteo por `fechainicio` atribuye 134 y 79 pasajeros a las horas 21 y 22 respectivamente, pero son artefactos del sello tardío: esos pasajeros ya están contados en su franja real de salida. El patrón replica el comportamiento documentado en el análisis de la Ruta K54, donde también se identificaron registros con marca de inicio diferida que desaparecen al usar fechasalida como referencia temporal.

In [36]:
_, _, _ = toolkit.plot_passengers_by_hour(
    df_prog, col_start="fechainicio",
    hours=(21, 22, 23),
    title="Pasajeros totales en horas 21-23",
    xlab="Hora del día (fecha de inicio)",
    ylab="Pasajeros totales"
)

La inspección de la hora 21 muestra un patrón distinto al documentado en la Ruta K54. De los 59 viajes con duración válida registrados en esa franja, dos presentan perfil comercial completo: corresponden a los últimos despachos de la jornada de dos vehículos distintos (`SOBUSA07` y `SOBUSA25`), con salidas físicas a las 20:44 y 20:45, duraciones de 182 y 172 minutos, y 42 y 16 pasajeros respectivamente. Sus `fechainicio` fueron sellados por el sistema 21.5 y 15.5 minutos después de la salida real, consistente con el patrón de sincronización diferida ya documentado. Ambos vehículos operaron con normalidad durante el día, con ciclos completos previos de 246 a 325 minutos. A diferencia de K54, donde se identificaron cinco casos similares concentrados en el vehículo `SOBUSA302`, en El Silencio los dos casos corresponden a vehículos distintos en fechas únicas.

In [37]:
df_check = df_prog.copy()
df_check["_hora"] = df_check["fechainicio"].dt.hour
df_check["_minuto"] = df_check["fechainicio"].dt.minute
df_check["_desfase_min"] = (
    (df_check["fechainicio"] - df_check["fechasalida"])
    .dt.total_seconds() / 60
)

subset = df_check[
    (df_check["_hora"] == 21) &
    (df_check["duracion_min"].notna()) &
    (df_check["es_cancelado"] == 0)
].copy()

# Plausibles: perfil comercial completo
mask_plausible = (
    subset["duracion_min"].between(135, 250) &
    (subset["numeropasajeros"] >= 15) &
    (subset["_desfase_min"].between(10, 30))
)

mask_con_pax = subset["numeropasajeros"] > 0

# Solo se excluyen los anómalos SIN pasajeros
mask_excluir = ~mask_plausible & ~mask_con_pax

plausibles = subset[mask_plausible].copy()
conservados = subset[mask_con_pax & ~mask_plausible].copy()
excluidos = subset[mask_excluir].copy()

# Tabla de plausibles
dias_es = {
    "Monday": "Lunes", "Tuesday": "Martes",
    "Wednesday": "Miércoles", "Thursday": "Jueves",
    "Friday": "Viernes", "Saturday": "Sábado", "Sunday": "Domingo",
}

plausibles["fecha"] = plausibles["fechainicio"].dt.strftime("%Y-%m-%d")
plausibles["dia_semana"] = plausibles["fechainicio"].dt.day_name().map(dias_es)
plausibles["hora_inicio"] = plausibles["fechainicio"].dt.strftime("%H:%M:%S")
plausibles["hora_salida"] = plausibles["fechasalida"].dt.strftime("%H:%M:%S")
plausibles["hora_fin"] = plausibles["fechafin"].dt.strftime("%H:%M:%S")

plausibles = plausibles.rename(columns={
    "fecha": "Fecha",
    "dia_semana": "Día de la semana",
    "hora_inicio": "Hora inicio",
    "hora_salida": "Hora salida",
    "hora_fin": "Hora fin",
    "duracion_min": "Duración (min)",
    "numeropasajeros": "Pasajeros",
    "idvehiculo": "Vehículo",
    "idprogramacion": "ID programación",
})

cols = ["Fecha", "Día de la semana", "Hora inicio", "Hora salida", "Hora fin",
        "Duración (min)", "Pasajeros", "Vehículo", "ID programación"]

tabla_plausibles = (
    plausibles[cols]
    .sort_values("Fecha")
    .reset_index(drop=True)
)

tabla_plausibles["Duración (min)"] = tabla_plausibles["Duración (min)"].round(1)

if len(tabla_plausibles) == 0:
    print("No hay viajes que cumplan el perfil plausible con los filtros actuales.")
else:
    _ = toolkit.dataframe_head_table(
        tabla_plausibles, n=len(tabla_plausibles)
    )

Fecha,Día de la semana,Hora inicio,Hora salida,Hora fin,Duración (min),Pasajeros,Vehículo,ID programación
2024-05-14,Martes,21:05:28,20:44:00,23:46:04,182.100000,42,SOBUSA07,6206402
2025-03-26,Miércoles,21:00:31,20:45:00,23:37:16,172.300000,16,SOBUSA25,6914564


Los 57 registros restantes no presentan perfil comercial y se clasifican como anómalos. Su distribución difiere de la observada en K54: no hay cierres inmediatos (< 10 min) y la mayoría (45 casos) cae en el rango intermedio 10–400 minutos, con 13 registros que superan los 400 minutos y un máximo de 3,661.6 minutos (61 horas). Tres viajes anómalos registran pasajeros (13, 15 y 25), todos con duraciones fuera del rango operativo, correspondientes a registros abiertos durante la noche. El vehículo `SOBUSA25` aparece en dos de esos tres casos, pero sin un patrón sistemático que permita atribuir el fenómeno a un dispositivo específico.

Se conservan en el análisis los dos casos plausibles, cuyas salidas físicas (20:44 y 20:45) caen dentro de la ventana operativa regular y cuyos perfiles de duración y demanda son consistentes con el cierre de jornada. No requieren confirmación adicional con el área operativa: son operación regular con registro tardío. De los 57 casos anómalos, los 54 sin pasajeros se excluyen por no contribuir a la demanda de ninguna franja, y los 3 restantes se conservan en el conjunto de datos.

In [38]:
mask_anomalo = ~mask_plausible
mask_con_pax = subset["numeropasajeros"] > 0
mask_excluir = mask_anomalo & ~mask_con_pax

indices_excluir = subset[mask_excluir].index
df_prog = df_prog.drop(index=indices_excluir)

El análisis acumulado de la duración de los 21,406 viajes con duración válida en la hora 5 (de 22,604 despachos totales, 1,198 cancelados sin cierre) muestra que las duraciones se concentran principalmente entre 180 y 300 minutos. El 23% acumulado se alcanza en los 150 minutos, la mediana se sitúa cerca de los 200 minutos (48.3%), y el 60% se acumula hasta los 220 minutos. A partir de ese punto el porcentaje aumenta rápidamente hasta superar el 96% alrededor de los 300 minutos, lo que confirma que la mayor parte de la masa de la distribución queda contenida por debajo de ese umbral.

In [19]:
df_h5 = df_prog.copy()
df_h5["_hora"] = df_h5["fechasalida"].dt.hour

df_h5 = df_h5[
    (df_h5["_hora"] == 5) &
    (df_h5["duracion_min"].notna())
].copy()

_, _, tabla = toolkit.plot_duration_ecdf(
    df_h5,
    thresholds=(20, 30, 60, 90, 120, 150, 180, 200, 220, 300, 400, 500),
    xlim=(0, 400),
    title="Distribución acumulada de la duración — Hora 5",
    xlab="Duración (min)", ylab="Porcentaje acumulado (%)"
)

Los extremos de la distribución son minoritarios pero informativos. Menos del 2% de los viajes tiene duración inferior a 90 minutos, pero la proporción salta al 18.5% al considerar el umbral de 120 minutos, lo que evidencia un grupo concentrado en el rango 90–120 minutos ya caracterizado en la sección anterior como recorrido parcial del arranque. En el extremo opuesto, los registros por encima de 300 minutos representan menos del 4%, con colas hasta 400 y 500 minutos (97.6% y 98.2% acumulados). En conjunto, la distribución evidencia una concentración principal en duraciones intermedias de 180 a 300 minutos, con grupos minoritarios en ambos extremos que requieren revisión individual.

Del total de 330 viajes cortos en la hora 5, 157 (47.6%) registran pasajeros con mediana de 18 abordajes (IQR 12–26), y los 173 restantes (52.4%) no registran pasajeros. La duración mediana es mayor en los que cargan (84.9 min) que en los vacíos (44.7 min), consistente con un perfil de servicio comercial en el primer grupo y de movimiento de posicionamiento en el segundo. La proporción de viajes sin pasajeros es notablemente más alta que en la Ruta K54, donde solo el 5.6% de los cortos estaban vacíos; en la ruta El Silencio, más de la mitad lo están. Los viajes cortos con pasajeros contribuyen a la serie de demanda por franja porque sus abordajes son efectivos; sin embargo, se excluyen del cálculo de indicadores operativos como el headway o la duración promedio del ciclo, dado que su extensión no representa un recorrido completo de la ruta.

In [20]:
_, _, tabla = toolkit.plot_long_trips_by_hour(
    df_prog, col_start="fechasalida", threshold_min=420,
    title="Distribución horaria de viajes > 420 min",
    xlab="Hora del día",
    ylab="Porcentaje de viajes largos (%)",
)

A diferencia de los viajes cortos, cuya concentración en la hora 5 fue verificada como operación real, los largos presentan un patrón completamente distinto: se concentran al cierre de la jornada, con tasas internas que crecen progresivamente desde 4.6% en la hora 15 hasta 11.9% en la hora 20, frente a valores inferiores al 1% en las horas intermedias del día. Los 4,861 viajes con duración superior a 420 minutos superan en 1.78× el ciclo mediano de la ruta (236 min), lo que descarta la operación comercial regular. Su perfil de pasajeros (mediana de 47 pasajeros, con 12.4% sin abordajes) se desvía del resto del dataset (mediana 76), pero el 87.6% registra al menos un abordaje y el 46.8% supera los 50 pasajeros, lo que indica que son viajes reales con cierre tardío más que registros vacíos. En consecuencia, sus pasajeros se conservan para el análisis de demanda por franja, mientras que su duración se excluye de las métricas operativas.

### Número de pasajeros

El análisis del número de pasajeros por viaje identificó 13 registros que superan los 280 pasajeros, umbral superior del filtro Hampel calculado como mediana global más 5 MADs escalados (74 + 5 × 1.4826 × 28 ≈ 282). A diferencia de la Ruta K54, no se detectaron bugs del sensor: el máximo del dataset es 508 pasajeros y los 13 casos se distribuyen entre 282 y 508. De ellos, 8 corresponden a viajes cancelados sin cierre registrado y se conservan en el dataset, ya que sus conteos de demanda son reales y no existe evidencia de que representen errores de registro.

De los 5 casos con duración válida, uno corresponde a la jornada del 2024-09-06. Esa fecha presenta un comportamiento atípico respecto a sus días vecinos: solo 39 viajes registrados frente a los ~132–136 habituales, una tasa de cancelación del 43.6% (vs ~11.6% en la ventana circundante) y un pax máximo de 373 frente a ~205 típico. Este patrón corresponde a un fallo del sistema de registro, no a operación real. Se excluye esa jornada del análisis, quedando 4 casos para evaluación posterior.

In [39]:
UMBRAL        = 280
UMBRAL_BUG    = 10000   # no-op en SILENCIO (máximo del dataset = 508)
fecha_anomala = pd.Timestamp("2024-09-06").date()

filtro1 = df_prog[df_prog["numeropasajeros"] > UMBRAL].copy()

filtro2 = filtro1[
    (filtro1["numeropasajeros"] < UMBRAL_BUG) &
    (filtro1["fechasalida"].dt.date != fecha_anomala) &
    (filtro1["duracion_min"].notna())
].copy()

cols = ["numeropasajeros", "fechasalida", "fechafin", "duracion_min",
        "idprogramacion", "idvehiculo"]

tabla_final = (
    filtro2[cols]
    .sort_values("numeropasajeros", ascending=False)
    .reset_index(drop=True)
    .rename(columns={
        "numeropasajeros": "Pasajeros",
        "fechasalida":     "Fecha salida",
        "fechafin":        "Fecha fin",
        "duracion_min":    "Duración (min)",
        "idprogramacion":  "ID programación",
        "idvehiculo":      "Vehículo",
    })
)

tabla_final["Duración (min)"] = tabla_final["Duración (min)"].round(1)

_ = toolkit.dataframe_head_table(tabla_final, n=len(tabla_final))

# --- Filtros aplicados a df_prog ---
df_prog = df_prog[
    (df_prog["numeropasajeros"] < UMBRAL_BUG) &
    (df_prog["fechasalida"].dt.date != fecha_anomala)
].copy()

Pasajeros,Fecha salida,Fecha fin,Duración (min),ID programación,Vehículo
368,2024-11-25 09:06:00,2024-11-25 20:09:34,663.600000,6641118,SOBUSA273
329,2024-12-05 10:51:00,2024-12-05 20:21:24,570.400000,6665517,SOBUSA568
319,2024-11-26 09:54:00,2024-11-26 20:53:02,659.000000,6643694,SOBUSA508
298,2024-09-09 14:00:00,2024-09-09 22:42:04,522.100000,6471272,SOBUSA409


De los 4 casos con más de 280 pasajeros que quedan tras excluir el día anómalo del 2024-09-06, todos presentan duraciones entre 522 y 664 minutos (8.7 a 11.1 horas), muy por encima del ciclo mediano de la ruta (237 min). Estas duraciones corresponden a registros que el sistema no cerró hasta la noche siguiente al arranque, abarcando múltiples ciclos operativos sin segmentar. Como la demanda se agrega por franja anclada a la hora de salida, incluir estos viajes asignaría los 368 pasajeros del viaje más cargado al intervalo de las 09:00–09:15, aunque en realidad se distribuyeron a lo largo de las ~44 franjas siguientes. Esto inflaría artificialmente la demanda de la franja de arranque y dejaría subrepresentadas las franjas intermedias. Los 4 casos se excluyen por consistencia con el filtro aplicado a la categoría de viajes largos: la marca de salida no constituye un anclaje válido para atribuir sus pasajeros a una única franja. Tras estos filtros, el dataset conserva 7 viajes cancelados (uno de los 8 originales correspondía a la jornada anómala) con conteos entre 282 y 508 pasajeros.

In [40]:
UMBRAL = 280
fecha_anomala = pd.Timestamp("2024-09-06").date()

mask_excluir = (
    (df_prog["numeropasajeros"] > UMBRAL) &
    (df_prog["duracion_min"].notna()) &
    (df_prog["fechasalida"].dt.date != fecha_anomala) &
    (df_prog["duracion_min"] > 420)
)

df_prog = df_prog[~mask_excluir].copy()

El análisis de viajes sin pasajeros por hora muestra un patrón en forma de U consistente con la operación normal de un sistema de transporte: las tasas son más altas al inicio (9.58% en hora 4, 6.45% en hora 5) y aumentan hacia el final de la jornada (2.24% en hora 19, 2.33% en hora 20), con un mínimo durante el valle operativo (0.76% en hora 11, con promedio de 1.14% entre las 10 y las 15 horas). El promedio general de viajes con 0 pax es 2.28%, con un máximo de 9.58% en la hora 4. No se identifican picos anómalos que sugieran fallos del sistema, aunque el arranque de jornada concentra una proporción de viajes sin pasajeros muy superior a la del resto del día. Los viajes sin pasajeros se conservan en el análisis porque representan operación real con baja demanda, no errores de registro.

In [41]:
_, _, tabla = toolkit.plot_zero_passenger_trips_by_hour(
    df_prog, col_start="fechasalida",
    title="Distribución horaria de viajes sin pasajeros", xlab="Hora del día",
    ylab="Porcentaje de viajes (%)"
)

La verificación de consistencia física (duración vs pasajeros) no identificó violaciones: ningún viaje con duración inferior a 90 min supera los 150 pasajeros, y ningún caso con más de 280 pasajeros conserva una duración válida tras aplicar los filtros previos.

Los largos > 420 min restantes suman 4,838 registros con 253,751 pasajeros (2.04% de la demanda del período), distribuidos en 1,010 jornadas únicas sin concentración específica. La mayor concentración diaria es de 24 registros, frente a los 32 del peor día en K54. A diferencia de esa ruta, en la ruta El Silencio no se identifica un conjunto de jornadas con fallo sistemático del sistema de segmentación: los largos aparecen de forma dispersa a lo largo de los tres años y su proporción sobre el total de viajes es estable entre días de la semana (2.5%–3.4%). Sus pasajeros se conservan para el análisis de demanda por franja.

## Agregación de datos

Siguiendo el mismo criterio aplicado en el análisis de la Ruta K54, se adoptan franjas de 15 minutos ancladas a la hora de salida del bus. Formalmente, sea $v$ un viaje con hora de salida $t_v$ (`fechasalida`) y volumen de pasajeros $p_v$ (`numeropasajeros`). Se define $\tau_v = 60 \cdot h(t_v) + m(t_v)$ como los minutos transcurridos desde la medianoche de $t_v$, donde $h(\cdot)$ y $m(\cdot)$ son la hora y el minuto de $t_v$. La franja a la que pertenece $v$ se define como:

$$\text{franja}(v) = \left\lfloor \frac{\tau_v}{\Delta} \right\rfloor \cdot \Delta, \quad \Delta = 15 \text{ min}$$

El conjunto de viajes de `df_prog_clean` que caen en una franja $f$ es $V_f = \{v : \text{franja}(v) = f\}$, y la variable agregada por franja se define como:

$$\text{pasajeros}(f) = \sum_{v \in V_f} p_v$$

La decisión de anclar en fechasalida, y no en fechainicio, responde a que la salida es el evento operativo real de despacho. Los datos de calendario y estacionalidad (`tipo_estacionalidad`, `nombre_evento`) se extraen de `timbradas_anio` mediante join por fecha, aprovechando que esa tabla vincula cada patrón estacional a un rango de fechas real (`fecha_inicio`, `fecha_fin`).

In [52]:
# Agregación por franja + join con calendario estacional (SILENCIO) ----

df_work = df_prog.copy()

df_work["franja_ts"] = df_work["fechasalida"].dt.floor("15min")

# Reasignar 20:45–20:59 a la franja 20:30 (ventana cierra a las 20:30)
mask_2045 = (
    (df_work["franja_ts"].dt.hour == 20) &
    (df_work["franja_ts"].dt.minute == 45)
)
df_work.loc[mask_2045, "franja_ts"] = (
    df_work.loc[mask_2045, "franja_ts"] - pd.Timedelta(minutes=15)
)

df_agre = (
    df_work.dropna(subset=["fechasalida"])
           .groupby("franja_ts")
           .agg(
               pasajeros = ("numeropasajeros", "sum"),
               n_viajes  = ("numeropasajeros", "size"),
           )
           .reset_index()
)

dias = pd.date_range(
    df_agre["franja_ts"].min().normalize(),
    df_agre["franja_ts"].max().normalize(),
    freq="D",
)

# Ventana SILENCIO: 04:30 – 20:30 (65 franjas/día)
slots_min = range(4 * 60 + 30, 20 * 60 + 30 + 1, 15)

esperado = pd.DatetimeIndex([
    d + pd.Timedelta(minutes=m)
    for d in dias
    for m in slots_min
])

df_agre = (
    df_agre.set_index("franja_ts")
           .reindex(esperado)
           .rename_axis("franja_ts")
           .reset_index()
)

df_agre["pasajeros"] = df_agre["pasajeros"].fillna(0).astype("int32")
df_agre["n_viajes"]  = df_agre["n_viajes"].fillna(0).astype("int16")

df_agre["anio"]       = df_agre["franja_ts"].dt.year
df_agre["mes"]        = df_agre["franja_ts"].dt.month
df_agre["dia"]        = df_agre["franja_ts"].dt.day
df_agre["dia_semana"] = df_agre["franja_ts"].dt.dayofweek + 1
df_agre["franja"]     = df_agre["franja_ts"].dt.time

df_cal = (
    df[["fecha_inicio", "fecha_fin", "tipo_estacionalidad", "nombre_evento"]]
    .drop_duplicates()
    .reset_index(drop=True)
)

prioridad = {
    "DIAS_CORRIENTES":    0,
    "TEMPORADA_NACIONAL": 1,
    "FESTIVO_NACIONAL":   2,
    "FIESTAS_PATRONALES": 3,
    "FIESTA_ATLANTICO":   4,
}
df_cal["_prio"] = df_cal["tipo_estacionalidad"].map(prioridad).fillna(0)
df_cal = df_cal.sort_values("_prio", ascending=False).reset_index(drop=True)

filas = []
for _, row in df_cal.iterrows():
    for d in pd.date_range(row["fecha_inicio"], row["fecha_fin"], freq="D"):
        filas.append({
            "fecha":               d.date(),
            "tipo_estacionalidad": row["tipo_estacionalidad"],
            "nombre_evento":       row["nombre_evento"],
        })

df_calendario = (
    pd.DataFrame(filas)
      .drop_duplicates(subset=["fecha"])
      .reset_index(drop=True)
)

df_agre["fecha"] = df_agre["franja_ts"].dt.date
df_agre = df_agre.merge(df_calendario, on="fecha", how="left")

df_agre = df_agre.set_index("franja_ts").sort_index()

df_agre = df_agre[
    ["franja", "anio", "mes", "dia", "dia_semana",
     "tipo_estacionalidad", "nombre_evento",
     "pasajeros", "n_viajes"]
]

El número de viajes despachados y el número de viajes cancelados por franja se excluyen del conjunto de features del modelo porque son resultados operativos conocidos únicamente después del cierre de la franja.

In [53]:
_ = toolkit.dataframe_integrity_blocks(df_agre, n_blocks=2)

Variable,Data type,Variable,Data type
franja,time,tipo_estacionalidad,str
anio,int32,nombre_evento,str
mes,int32,pasajeros,int32
dia,int32,n_viajes,int16
dia_semana,int32,,


La forma de agregación adoptada garantiza tres propiedades sobre el dataset resultante: (i) no existen franjas huérfanas dentro de la ventana operativa —cada uno de los 1.096 días contiene exactamente las 65 franjas de 15 minutos entre 04:30 y 20:30—; (ii) no existen días sin ningún despacho, salvo un único caso identificado; y (iii) no existen valores nulos en ninguna columna.

Se contrastó la demanda derivada de `progvehiculos` (`df_agre`) con los consolidados por patrón de `timbradas_anio` sobre 3.139 patrones presentes en ambas fuentes. La mediana del ratio `subidas_agre / subidas_timb` es 1.26, con rango intercuartílico (0.68, 2.64).

El diagrama de dispersión del ratio frente al número de días que componen cada patrón muestra una estructura discreta: los puntos se agrupan en bandas verticales nítidas, con dispersión amplia dentro de cada banda. La correlación de Spearman ($\rho$ = 0.072) y la tau de Kendall ($\tau$ = 0.051) son cercanas a cero, lo que indica ausencia de asociación monotónica entre la frecuencia del patrón y el ratio.

In [56]:
_, _, _, _ = toolkit.plot_ratio_vs_frequency(
    df_agre, df,
    title="Ratio de abordajes: operativo / anual",
    xlab="Días que componen el patrón",
    ylab="Ratio de abordajes (log)"
)

La conclusión operativa es que `timbradas_anio_k54` es una fuente válida como referencia agregada, dado que la mediana se sitúa próxima a 1, pero no como fuente primaria del target. El modelo requiere la resolución por fecha específica que solo `progvehiculos` proporciona, y la divergencia a nivel de patrón individual impide utilizar `timbradas_anio` como ground truth por franja. La estructura discreta del diagrama confirma además que los patrones no son continuos sino eventos agrupados por el calendario operativo. La tabla se utiliza únicamente para el mapeo calendario–estacionalidad (`tipo_estacionalidad`, `nombre_evento`, `fecha_inicio`, `fecha_fin`).

## Caracterización de la demanda

Sobre el conjunto agregado `df_agre` se realiza la caracterización de la demanda. El análisis parte de la serie temporal diaria de pasajeros, examina su distribución por franja, y descompone sus patrones de estacionalidad intradía, semanal y anual. El objetivo es identificar qué dimensiones temporales modulan la demanda de forma significativa, y por tanto merecen representación explícita en el modelo, y cuáles no aportan señal predictiva.

El conjunto de datos se dividió en dos subconjuntos mediante una partición cronológica 80/20, con corte en 2025-05-26 17:30:00. El subconjunto de entrenamiento contiene las primeras 56.992 franjas del período, abarcando desde 2023-01-01 04:30:00 hasta 2025-05-26 17:15:00. El subconjunto de prueba (denominado *holdout set*) contiene las 14.248 franjas restantes, desde 2025-05-26 17:30:00 hasta 2025-12-31 20:30:00.

In [59]:
train, test, fecha_corte = toolkit.split_and_save(df_agre)

Saved:
  ..\data\processed\train.parquet    — 56,992 time slots
  ..\data\processed\holdout.parquet  — 14,248 time slots

Cutoff date: 2025-05-26 17:30:00
Train: 2023-01-01 04:30:00 → 2025-05-26 17:15:00
Test:  2025-05-26 17:30:00 → 2025-12-31 20:30:00

Train share:   80.0 %
Holdout share: 20.0 %


La serie diaria agregada por suma expone la estructura general de la demanda en el período. Se distinguen interrupciones puntuales, reconocibles como caídas abruptas hacia valores cercanos a cero en días aislados, cuyo patrón sugiere la incidencia de eventos externos sobre la operación (por ejemplo, septiembre de 2024). Se insinúa además una modulación de escala mayor, con ascensos hacia el final de la primera mitad del año y descensos al cierre del año.

A nivel de franja, la demanda sigue un perfil bimodal dentro de cada jornada: un primer pico en la mañana, un valle al mediodía y un segundo pico al final de la tarde. Ese perfil se modula por un ciclo semanal marcado, visible como la alternancia entre días laborales de alta actividad y fines de semana de menor demanda. La forma del perfil intradía se mantiene entre semanas de distintos meses (marzo de 2023, septiembre de 2024), lo que sugiere que el patrón es estructural y no depende de la estación. Un evento como el de septiembre de 2024 irrumpe de forma abrupta en la serie, pero el patrón de los días adyacentes se mantiene: una vez concluido el evento, la demanda retoma el nivel y la forma previos.

In [61]:
_, _ = toolkit.plot_temporal_panel(
    train, zoom_left=("2023-03-06", "2023-03-12"),
    zoom_right=("2024-09-02", "2024-09-08"),
    text_left="marzo 2023", text_right="septiembre 2024",
    title="Demanda de pasajeros (2023-2025)",
    xlab_zoom="Día del mes", ylab_daily="Pasajeros por día",
    ylab_zoom="Pasajeros por franja", hspace=0.05
)

En comparación con K54, la demanda de SILENCIO es consistentemente menor en términos absolutos (11.323 pasajeros/día frente a 22.390 en K54), a pesar de que la ruta es más extensa (62.9 km vs. 56.4 km). Esta diferencia es coherente con un menor número de despachos diarios (146 viajes/día frente a aproximadamente 269 en K54), lo que sugiere que la ruta opera con una frecuencia base menor. La ocupación media por viaje es similar entre ambas rutas (77.7 pasajeros/viaje en SILENCIO frente a aproximadamente 83 en K54), lo que indica que la diferencia en demanda absoluta responde principalmente a la intensidad de la oferta y no a una menor utilización de los vehículos.

La ACF sobre la serie por franja, calculada con 500 rezagos, muestra una oscilación sostenida con picos regulares cada 32-33 rezagos (media jornada operativa: 65 franjas/día entre 04:30 y 20:30), reflejo del perfil bimodal intradía. Los picos aparecen también en múltiplos de 65 (días completos) y su amplitud forma un sobre con máximo en el rezago 455 (7 × 65, una semana operativa). La estructura replica exactamente lo observado en K54 —misma secuencia de picos, mismo intervalo semi-diurno, misma periodicidad diaria, pese a que SILENCIO opera con aproximadamente la mitad de los despachos diarios (~146 vs. ~269 viajes/día). La PACF cae abruptamente tras el primer rezago, con residuos pequeños pero sistemáticos en los múltiplos de 65, lo que confirma una memoria de corto plazo dominante sobre una componente estacional diaria, patrón también compartido con K54.

In [64]:
_, _ = toolkit.plot_acf_pacf(
    train["pasajeros"],
    lags=500, figsize=(12, 4),
    titles=("Autocorrelación (ACF)", "Autocorrelación parcial (PACF)"),
    xlab="Rezago", ylab="Autocorrelación",
)

La serie diferenciada mediante `diff(65)` remueve la dependencia de cada franja respecto al mismo slot del día anterior y expone la estructura que el ciclo diario enmascaraba. La ACF cae en los primeros rezagos, se mantiene prácticamente plana en torno a cero entre los rezagos 100 y 400, y muestra un rebote positivo en el rezago 455 (7 × 65, una semana operativa completa). Ese rebote confirma que la estacionalidad semanal persiste tras eliminar el ciclo diario, y es el mismo patrón observado en K54: ambas rutas revelan una semana operativa como unidad estructural subyacente.

La PACF sobre la serie diferenciada presenta picos en los múltiplos de 65 (65, 130, 195, 260, 325, 390, 455), más visibles que en la serie original. Esa mejora indica que la correlación parcial a escala diaria estaba siendo absorbida por la autocorrelación de corto plazo y emerge como estructura sistemática al removerla. El patrón coincide con el de K54; la única diferencia es que la zona negativa intermedia de la ACF es más somera en SILENCIO, consistente con su menor volumen absoluto de demanda.

In [65]:
_, _ = toolkit.plot_acf_pacf(
    train["pasajeros"].diff(65).dropna(),
    lags=500, figsize=(12, 4),
    titles=("Autocorrelación (ACF)", "Autocorrelación parcial (PACF)"),
    xlab="Rezago", ylab="Autocorrelación",
)

La distribución de pasajeros por franja se caracteriza por una forma asimétrica con cola hacia la derecha: la mayor parte de las franjas se concentra en valores bajos y medios, con un único pico en torno a 150-180 pasajeros por franja, y la frecuencia decae de forma sostenida hacia valores altos. Esa morfología, unimodal y sin hombros secundarios, difiere de la observada en K54, donde la distribución presenta una moda principal en torno a 200 pasajeros por franja y un hombro secundario menos pronunciado alrededor de 400. En SILENCIO ese hombro no se manifiesta, lo que sugiere un perfil intradía menos marcado o una menor separación entre los picos de la mañana y de la tarde.

Se observa además una proporción apreciable de franjas sin pasajeros reportados (~4% del total). Esas franjas responden a distintas causas: intervalos sin despacho, franjas donde la demanda estuvo limitada por eventos externos, y franjas de borde de jornada donde la operación es naturalmente de baja actividad.

A escala anual, la demanda diaria promedio muestra una caída entre 2023 y 2024 (de 12.986 a 11.754 pasajeros/día, −9.5%), seguida de una leve recuperación en 2025 (11.916, +1.4% respecto a 2024). El patrón de caída y recuperación es análogo al de K54 (26.238 → 23.585 → 24.038), aunque ruta de El Silencio opera con aproximadamente la mitad de la demanda diaria.

In [68]:
_, _, _ = toolkit.plot_distribution_and_yearly_demand(
    train, titles=("Distribución de pasajeros por franja",
            "Demanda diaria por año"),
    xlab_hist="Pasajeros por franja", ylab_hist="Frecuencia relativa",
    xlab_bar="Año", ylab_bar="Pasajeros por día"
)

La demanda agregada por mes, combinando los tres años mediante la mediana de los totales diarios, sugiere un perfil bimodal dentro del año. La primera cresta se extiende de febrero a mayo, con máximo en febrero (13.832 pasajeros/día). Un descenso aparece en junio y julio, con mínimo en junio (11.006). La segunda cresta se desarrolla de agosto a noviembre, con máximo en agosto (13.790), y la serie desciende hacia diciembre (11.168). La diferencia entre la primera y la segunda cresta es mínima (42 pasajeros/día), por lo que ambas pueden considerarse de magnitud equivalente.

El patrón es análogo al observado en K54: ambas rutas presentan dos crestas anuales con el mismo calendario (febrero-mayo y agosto-noviembre), valle en junio-julio, y la misma caída sostenida de la demanda entre 2023 y 2025 en prácticamente todos los meses.

In [67]:
_, _, _ = toolkit.plot_demand_by_month(
    train, xlab="Mes", ylab="Pasajeros por día",
    title="Demanda diaria por mes y año",
    month_labels=("Ene", "Feb", "Mar", "Abr", "May", "Jun",
                  "Jul", "Ago", "Sep", "Oct", "Nov", "Dic")
)

La demanda por día de la semana reproduce el patrón ya sugerido por la serie diaria y la ACF. Los días laborales (lunes a viernes) concentran la mayor demanda y se mantienen en un rango estrecho entre sí (12.860 a 13.482 pasajeros/día), sin una estructura interna clara dentro del bloque laboral. El sábado marca una caída intermedia (10.666 pasajeros/día, ≈80% del promedio laboral), y el domingo registra el nivel más bajo de la semana (6.462 pasajeros/día, ≈48% del promedio laboral, es decir, cercano a la mitad). La separación entre el bloque lunes-viernes y el fin de semana es marcada. El patrón coincide con el observado en K54, donde también se documentó un bloque laboral homogéneo, sábado intermedio y domingo con la mitad del promedio laboral.

La caída sostenida entre años, ya documentada en el análisis mensual, se mantiene en la mayoría de los días de la semana, con 2023 como el año de mayor demanda en cada categoría. Las únicas excepciones son el miércoles (donde 2025 supera levemente a 2024) y el domingo (donde 2023 y 2024 son prácticamente equivalentes).

In [70]:
_, _, _ = toolkit.plot_demand_by_weekday(
    train, xlab="Día de la semana", ylab="Pasajeros por día",
    title="Demanda diaria por día de la semana y año",
    weekday_labels=("Lun", "Mar", "Mié", "Jue", "Vie", "Sáb", "Dom")
)

El perfil intradía conserva una forma bimodal común a los tres años: pico único en la mañana (05:30), valle extendido alrededor del mediodía (10:30–11:30), segundo pico en la tarde (14:00–14:30) y descenso progresivo hacia el cierre. A diferencia de K54, donde el perfil matutino presenta dos crestas de altura similar (05:30 y 06:30) seguidas de un descenso escalonado, en la ruta de El Silencio el bloque matutino muestra un pico único a las 05:30 seguido de un declive monótono hasta el valle. La amplitud relativa de los dos picos también difiere: en la ruta de El Silencio el pico matutino es aproximadamente 1,7 veces el vespertino (433 vs. 257,5 pasajeros/franja), frente a ~1,4 en K54, lo que indica una concentración mayor de la demanda en la primera mitad de la jornada.

La variación entre años no se distribuye uniformemente a lo largo del día. El año 2023 se separa hacia arriba en el pico matutino (05:30), las series convergen entre 06:30 y 13:30, y vuelven a separarse en la tarde, manteniendo la brecha hasta el cierre. El efecto del año, por tanto, no es aditivo: se concentra en los dos picos de demanda y se atenúa en el valle extendido del mediodía.

In [71]:
_, _, _ = toolkit.plot_demand_by_time_slot(
    train, xlab="Franja horaria", ylab="Pasajeros (mediana)", 
    title="Demanda por franja horaria y año"
)

La demanda diaria no es homogénea entre tipos de día. Los días corrientes concentran el nivel más alto (12.175 pasajeros/día) y funcionan como base de la operación. Los días de Fiesta del Atlántico se mantienen cercanos a ese nivel (11.016, ≈90% del base), lo que sugiere que eventos como el Carnaval no reducen la operación sino que la sostienen en valores relativamente altos. La Temporada Nacional y el Festivo Nacional sí reducen la demanda, con magnitudes distintas: la temporada cae a un nivel intermedio (6.466, ≈53% del base) y el festivo es el que produce la mayor reducción (5.904, ≈48% del base). Los tipos de día especiales, por tanto, no actúan como un bloque uniforme: cada uno modula la demanda de forma distinta, y el efecto no es intercambiable entre categorías.

El ordenamiento relativo de las cuatro categorías coincide con el observado en K54 (corrientes > Fiesta Atlántico > Temporada > Festivo), aunque las magnitudes absolutas son sistemáticamente menores en la ruta de El Silencio, coherente con el menor volumen de demanda de la ruta ya documentado.

In [72]:
_, _, tabla = toolkit.plot_demand_by_seasonality(
    df_agre, xlab="Tipo de estacionalidad",
    ylab="Pasajeros por día",
    title="Demanda diaria por tipo de estacionalidad y año",
    category_labels=("Días corrientes", "Fiesta del Atlántico",
                     "Temporada nacional", "Festivo nacional"),
)

## Conclusiones e implicaciones

El análisis exploratorio de SILENCIO conduce a las mismas conclusiones de diseño que el de K54. La demanda tiene estructura multi-escala: los picos semi-diurnos en la ACF (cada 32-33 rezagos), los diarios (cada 65) y el rebote semanal en la ACF diferenciada (rezago 455) confirman el perfil bimodal intradía y el ciclo semanal superpuesto, idénticos a los de K54. En consecuencia, los lags del modelo deben construirse a esas escalas y complementarse con codificación seno/coseno de hora, día de semana y mes. El tipo de estacionalidad, por su parte, no actúa como bloque uniforme: los días corrientes y las Fiestas del Atlántico sostienen la demanda en niveles altos, mientras que la Temporada Nacional y los Festivos Nacionales la reducen con magnitudes distintas, mismo ordenamiento relativo observado en K54, lo que sugiere one-hot o codificación ordinal explícita.
